# Py-CoSim
EnergyPlus Python EMS-Based Co-Simulation Framework\
Author: Liang Zhang @ UArizona\
The is a work in progress. Check all the TODOs\
This is cleaned version based on `history_versions_2/example_run_clean_version_add_ML_control-mannual input_and_chatgpt_disabled_DL_occ_change_htg_to_clg_update_dir_PyCoSim.ipynb`

## Tested Versions
EnergyPlus Version: 22.2.0\
EnergyPlus API version: 0.2\
Python: 3.8.2

## Installation
Download and install the latest version of [Conda](https://www.anaconda.com/products/distribution)\
Run Anaconda Prompt as Administrator\
Create a new conda environment:\
`$ conda create -n <enter-the-name-of-repository-here> python=3.8.2 pip`
`$ activate <enter-the-name-of-repository-here>`
Ensure that you have navigated to the top level of your cloned repository. You will execute all your pip commands from this location. For example:\
`$ cd /path/to/repository`
Install the environment needed for this repository:\
`$ pip install -e .[dev]`

### Potential Usage
For single buildings
1. Test latest ML and control algorithms for single bulidings

For multiple buildings (community)
1. Community-scale co-simulation and operations among buildings, DER, ESS, and interdisciplianry components

### Connection with Other Components
1. Distributed Energy Resources (DER)
2. Energy Storage (Battery and Ice Storage)
3. Decision Making and Optimization Component
4. Artificial Intellegence, such as deep learning models (DL) and large language models (LLM)

### Paper
1. `Box\Liang and Alyssa Collaboration Folder\Python-EMS-Based Building Simulation Infrastructure`

### Resources
1. https://github.com/jmarrec/OpenStudio_to_EnergyPlusAPI/blob/main/OpenStudio_to_EnergyPlusAPI.ipynb
2. Py EMS API documentation
https://nrel.github.io/EnergyPlus/api/python/datatransfer.html
3. Available variable handles: EnergyPlusV22-2-0 : Input Output Reference: Page 2831

### TODO
1. function_n_data (bulding components)
- TODO: Inside function_n_data, eppy is used to identify all zone names and controllables
- TODO: use decorator
- TODO: export facility electricity, but don't know what is the variable handels.
- TODO: need a standardized timestamp. Should the timestamp be a global variable?
- TODO: used to use number of files to control timestep of two EnergyPlus models, next step should be using timestamp to sync all EnergyPlus models
2. Message Systems
- Use existing Python package 1) ZeroMQ, 2) RabbitMQ, and 3) pypubsub
3. Component Prioritazation
- Add attribute of prioritation for each component to decide the order of component run
4. Multiprocessing
- With threading, communication between running multiple instances is quite easy as you can just communicate using a messaging library like pypubsub to initiate signaling between the threads. With multiprocessing, communication is more difficult, but there are likely ways around it.
- mpi4py: "I am currently also working on a parallel programming project using the E+-API in Python.We are using mpi4py for the communication between the different instances of the E+-Buildings. We wanted to divide on core into multiple threads, and on each thread we could simulate one building at the same time. But in python there is the Global Interpreter lock, which usually is not allowing any multithreading applications.(https://realpython.com/python-gil/)"
5. TODOs in the code
6. Others
- Rhinoceros, Grasshopper, honeybee??Honeybee connects Rhino geometry and Grasshopper functionality to a selection of advanced energy modeling and simulation programs such as Radiance, Daysim, EnergyPlus, OpenStudio, and gbXML.
- Work with dompc: https://github.com/do-mpc/do-mpc
- Work with NeuroMANCER: https://github.com/pnnl/neuromancer
- In terms of parallel computing: another way to do it is to create multiple python script and run them together through bash: e.g., "python script1.py & python script2.py"
- Modualize
- hardcode year to 2009
- Docker
- Stability of online visualization

In [1]:
# built-in envrionment
import glob
import time
import datetime
import sys
sys.path.insert(0, 'C:/EnergyPlusV22-2-0/') # add EnergyPlus directory to system path
import os
working_path = os.getcwd() # get working path


# Py EMS modules
from pyenergyplus.api import EnergyPlusAPI

# Enable online plotting in Jupyter Notebook
%matplotlib notebook
import matplotlib.pyplot as plt

# basic data science package
import numpy as np
import pandas as pd

# Make co-simulation without randomness
# np.random.seed(123)

# threading for run components at the same time
from threading import Thread

# Enable Interactive user input
import tkinter as tk
from tkinter import simpledialog

# OpenAI to use LLM
import openai

# Pytorch for deep learning
import torch.nn as nn
import torch
os.environ['KMP_DUPLICATE_LIB_OK']='TRUE' #enable the threading to work with PyTorch

#packages about IML
np.random.seed(42)
import pickle

In [9]:
# generate random cooling setpoint
clg_random = np.random.uniform(22, 30, size=(1000,1))

x1:25.007256995586832,x2:24.0370980659134,e1: 1224.2840588176193,e2:2131.4655779713185
DR:1400.0, DR:10000.0
cost_function:3355.749636788938
u1:25,u2:25
x1:25.007256995586832,x2:24.98840211251947,e1: 1224.2840588176193,e2:1209.281444382474
DR:1400.0, DR:10000.0
cost_function:2433.565503200093
u1:25,u2:26
x1:25.007256995586832,x2:26.012505713195996,e1: 1224.2840588176193,e2:576.1667336681398
DR:1400.0, DR:10000.0
cost_function:1800.4507924857592
u1:26,u2:22
x1:26.02200581838536,x2:22.616334801243443,e1: 567.5887167374306,e2:4067.3034964781687
DR:1400.0, DR:10000.0
cost_function:4634.892213215599
u1:26,u2:23
x1:26.02200581838536,x2:23.163079581714793,e1: 567.5887167374306,e2:3473.5753788529214
DR:1400.0, DR:10000.0
cost_function:4041.164095590352
u1:26,u2:24
x1:26.02200581838536,x2:24.043267007918157,e1: 567.5887167374306,e2:2120.002435714667
DR:1400.0, DR:10000.0
cost_function:2687.591152452098
u1:26,u2:25
x1:26.02200581838536,x2:25.009479376306814,e1: 567.5887167374306,e2:1224.28405881

x1:26.02230048231612,x2:26.02230048231612,e1: 1356.1428135894519,e2:1356.1428135894519
DR:10000.0, DR:10000.0
cost_function:2712.2856271789037
Cooling Setpoint: 26
-----------------10----------------
u1:22,u2:22
x1:22.591943943989722,x2:22.5169460463211,e1: 4301.657167133333,e2:4350.917509850143
DR:10000.0, DR:10000.0
cost_function:8652.574676983477
u1:22,u2:23
x1:22.591943943989722,x2:23.055751648660912,e1: 4301.657167133333,e2:3000.7095009479594
DR:10000.0, DR:10000.0
cost_function:7302.366668081293
u1:22,u2:24
x1:22.591943943989722,x2:24.02266907264457,e1: 4301.657167133333,e2:2402.6338063224266
DR:10000.0, DR:10000.0
cost_function:6704.29097345576
u1:22,u2:25
x1:22.591943943989722,x2:24.93926805919818,e1: 4301.657167133333,e2:1560.250217459544
DR:10000.0, DR:10000.0
cost_function:5861.907384592877
u1:22,u2:26
x1:22.591943943989722,x2:25.56021567254195,e1: 4301.657167133333,e2:1229.6345244288677
DR:10000.0, DR:10000.0
cost_function:5531.291691562201
u1:23,u2:22
x1:23.164990644866485

x1:22.589013583076415,x2:23.055751648660912,e1: 4301.657167133333,e2:2977.706760254079
DR:10000.0, DR:10000.0
cost_function:7279.363927387412
u1:22,u2:24
x1:22.589013583076415,x2:24.021646098059904,e1: 4301.657167133333,e2:2404.873022888748
DR:10000.0, DR:10000.0
cost_function:6706.530190022081
u1:22,u2:25
x1:22.589013583076415,x2:24.940377490382026,e1: 4301.657167133333,e2:1582.1183469270597
DR:10000.0, DR:10000.0
cost_function:5883.775514060393
u1:22,u2:26
x1:22.589013583076415,x2:25.558945531971922,e1: 4301.657167133333,e2:1216.4944278901787
DR:10000.0, DR:10000.0
cost_function:5518.151595023512
u1:23,u2:22
x1:23.164990644866485,x2:22.549740245019755,e1: 3320.9129634046317,e2:4323.166114287124
DR:10000.0, DR:10000.0
cost_function:7644.0790776917565
u1:23,u2:23
x1:23.164990644866485,x2:23.094242115100727,e1: 3320.9129634046317,e2:3159.0774360346986
DR:10000.0, DR:10000.0
cost_function:6479.99039943933
u1:23,u2:24
x1:23.164990644866485,x2:24.022838028077725,e1: 3320.9129634046317,e2:2

x1:23.169446448385564,x2:24.941734735949822,e1: 4343.445736783959,e2:1687.8091189108195
DR:10000.0, DR:1500.0
cost_function:100000000.0
u1:23,u2:26
x1:23.169446448385564,x2:25.85869684084513,e1: 4343.445736783959,e2:1574.790401604231
DR:10000.0, DR:1500.0
cost_function:100000000.0
u1:24,u2:22
x1:24.05138794619005,x2:22.567922604050995,e1: 2759.772161525125,e2:4658.540812279516
DR:10000.0, DR:1500.0
cost_function:100000000.0
u1:24,u2:23
x1:24.05138794619005,x2:23.146013617564073,e1: 2759.772161525125,e2:4329.084572056302
DR:10000.0, DR:1500.0
cost_function:100000000.0
u1:24,u2:24
x1:24.05138794619005,x2:24.043703853666788,e1: 2759.772161525125,e2:2759.772161525125
DR:10000.0, DR:1500.0
cost_function:100000000.0
u1:24,u2:25
x1:24.05138794619005,x2:24.96109768673916,e1: 2759.772161525125,e2:1710.1484720563456
DR:10000.0, DR:1500.0
cost_function:100000000.0
u1:24,u2:26
x1:24.05138794619005,x2:25.970495967242996,e1: 2759.772161525125,e2:1538.2053220739167
DR:10000.0, DR:1500.0
cost_function

x1:24.935730213335354,x2:24.047843133097246,e1: 1890.0690412869642,e2:2775.8562517403097
DR:1500.0, DR:10000.0
cost_function:100000000.0
u1:25,u2:25
x1:24.935730213335354,x2:24.98430016976371,e1: 1890.0690412869642,e2:1943.3844173660461
DR:1500.0, DR:10000.0
cost_function:100000000.0
u1:25,u2:26
x1:24.935730213335354,x2:26.01679243915526,e1: 1890.0690412869642,e2:1716.2857510733056
DR:1500.0, DR:10000.0
cost_function:100000000.0
u1:26,u2:22
x1:25.638429088798226,x2:22.61493753634155,e1: 1569.6126324283362,e2:4656.52924472117
DR:1500.0, DR:10000.0
cost_function:100000000.0
u1:26,u2:23
x1:25.638429088798226,x2:23.16712923850037,e1: 1569.6126324283362,e2:4381.569304649677
DR:1500.0, DR:10000.0
cost_function:100000000.0
u1:26,u2:24
x1:25.638429088798226,x2:24.04902820160052,e1: 1569.6126324283362,e2:2775.8562517403097
DR:1500.0, DR:10000.0
cost_function:100000000.0
u1:26,u2:25
x1:25.638429088798226,x2:24.99392242323431,e1: 1569.6126324283362,e2:1966.4268986206555
DR:1500.0, DR:10000.0
cost

...

x1:25.017031161042233,x2:24.045619440558767,e1: 1745.0779095339876,e2:2556.261252582224
DR:10000.0, DR:10000.0
cost_function:4301.339162116212
u1:25,u2:25
x1:25.017031161042233,x2:24.99665817180548,e1: 1745.0779095339876,e2:1745.0427386417691
DR:10000.0, DR:10000.0
cost_function:3490.1206481757567
u1:25,u2:26
x1:25.017031161042233,x2:26.012623430756115,e1: 1745.0779095339876,e2:1166.8313377761342
DR:10000.0, DR:10000.0
cost_function:2911.909247310122
u1:26,u2:22
x1:26.018021784168536,x2:22.558823084603514,e1: 1157.2536100550983,e2:4527.979447308208
DR:10000.0, DR:10000.0
cost_function:5685.233057363306
u1:26,u2:23
x1:26.018021784168536,x2:23.1604337145635,e1: 1157.2536100550983,e2:4008.538335889023
DR:10000.0, DR:10000.0
cost_function:5165.791945944122
u1:26,u2:24
x1:26.018021784168536,x2:24.051274410142415,e1: 1157.2536100550983,e2:2558.781690893108
DR:10000.0, DR:10000.0
cost_function:3716.0353009482064
u1:26,u2:25
x1:26.018021784168536,x2:25.01986501017606,e1: 1157.2536100550983,e2:

x1:23.1604337145635,x2:23.079106527348873,e1: 4008.538335889023,e2:3904.7420795282246
DR:10000.0, DR:10000.0
cost_function:7913.280415417248
u1:23,u2:24
x1:23.1604337145635,x2:24.025927876564328,e1: 4008.538335889023,e2:2559.9436281540375
DR:10000.0, DR:10000.0
cost_function:6568.4819640430605
u1:23,u2:25
x1:23.1604337145635,x2:24.94693951433929,e1: 4008.538335889023,e2:1706.5259353160516
DR:10000.0, DR:10000.0
cost_function:5715.064271205075
u1:23,u2:26
x1:23.1604337145635,x2:25.84239385073394,e1: 4008.538335889023,e2:1234.1785937123218
DR:10000.0, DR:10000.0
cost_function:5242.716929601345
u1:24,u2:22
x1:24.04807621272754,x2:22.54064713195316,e1: 2556.261252582224,e2:4527.979447308208
DR:10000.0, DR:10000.0
cost_function:7084.240699890433
u1:24,u2:23
x1:24.04807621272754,x2:23.13231785190531,e1: 2556.261252582224,e2:3968.2613136925274
DR:10000.0, DR:10000.0
cost_function:6524.522566274752
u1:24,u2:24
x1:24.04807621272754,x2:24.03971124231625,e1: 2556.261252582224,e2:2567.724394838875

x1:26.018021784168536,x2:25.01986501017606,e1: 1157.2536100550983,e2:1745.0779095339876
DR:10000.0, DR:10000.0
cost_function:2902.331519589086
u1:26,u2:26
x1:26.018021784168536,x2:26.018021784168536,e1: 1157.2536100550983,e2:1157.2536100550983
DR:10000.0, DR:10000.0
cost_function:2314.5072201101966
Cooling Setpoint: 26
-----------------24----------------
u1:22,u2:22
x1:22.558823084603514,x2:22.48317264119528,e1: 4527.979447308208,e2:4498.566087380958
DR:10000.0, DR:10000.0
cost_function:9026.545534689167
u1:22,u2:23
x1:22.558823084603514,x2:23.043609487231638,e1: 4527.979447308208,e2:3890.976308113885
DR:10000.0, DR:10000.0
cost_function:8418.955755422094
u1:22,u2:24
x1:22.558823084603514,x2:24.01425554462238,e1: 4527.979447308208,e2:2568.8944971471265
DR:10000.0, DR:10000.0
cost_function:7096.873944455335
u1:22,u2:25
x1:22.558823084603514,x2:24.945323837975998,e1: 4527.979447308208,e2:1706.5259353160516
DR:10000.0, DR:10000.0
cost_function:6234.50538262426
u1:22,u2:26
x1:22.5588230846

x1:23.1604337145635,x2:25.84239385073394,e1: 4008.538335889023,e2:1234.1785937123218
DR:10000.0, DR:10000.0
cost_function:5242.716929601345
u1:24,u2:22
x1:24.04807621272754,x2:22.54064713195316,e1: 2556.261252582224,e2:4527.979447308208
DR:10000.0, DR:10000.0
cost_function:7084.240699890433
u1:24,u2:23
x1:24.04807621272754,x2:23.13231785190531,e1: 2556.261252582224,e2:3968.2613136925274
DR:10000.0, DR:10000.0
cost_function:6524.522566274752
u1:24,u2:24
x1:24.04807621272754,x2:24.03971124231625,e1: 2556.261252582224,e2:2567.724394838875
DR:10000.0, DR:10000.0
cost_function:5123.985647421099
u1:24,u2:25
x1:24.04807621272754,x2:24.96863082038156,e1: 2556.261252582224,e2:1734.0770278341204
DR:10000.0, DR:10000.0
cost_function:4290.338280416345
u1:24,u2:26
x1:24.04807621272754,x2:25.962004916382707,e1: 2556.261252582224,e2:1202.6249400046522
DR:10000.0, DR:10000.0
cost_function:3758.8861925868764
u1:25,u2:22
x1:25.017031161042233,x2:22.54892850086963,e1: 1745.0779095339876,e2:4527.979447308

x1:25.017031161042233,x2:24.045619440558767,e1: 1745.0779095339876,e2:2556.261252582224
DR:10000.0, DR:10000.0
cost_function:4301.339162116212
u1:25,u2:25
x1:25.017031161042233,x2:24.99665817180548,e1: 1745.0779095339876,e2:1745.0427386417691
DR:10000.0, DR:10000.0
cost_function:3490.1206481757567
u1:25,u2:26
x1:25.017031161042233,x2:26.012623430756115,e1: 1745.0779095339876,e2:1166.8313377761342
DR:10000.0, DR:10000.0
cost_function:2911.909247310122
u1:26,u2:22
x1:26.018021784168536,x2:22.558823084603514,e1: 1157.2536100550983,e2:4527.979447308208
DR:10000.0, DR:10000.0
cost_function:5685.233057363306
u1:26,u2:23
x1:26.018021784168536,x2:23.1604337145635,e1: 1157.2536100550983,e2:4008.538335889023
DR:10000.0, DR:10000.0
cost_function:5165.791945944122
u1:26,u2:24
x1:26.018021784168536,x2:24.051274410142415,e1: 1157.2536100550983,e2:2558.781690893108
DR:10000.0, DR:10000.0
cost_function:3716.0353009482064
u1:26,u2:25
x1:26.018021784168536,x2:25.01986501017606,e1: 1157.2536100550983,e2:

### Building 1 Class

In [3]:
class function_n_data:
    
    """
    __init__: defines class inputs and variables
    init_plot: defines the initial status of online visualization
    update_line: defines how online visualization is updated
    callback_function: the key function that define the interaction between Python and EnergyPlus
    """

    def __init__(self, building_id, building_info, filename_to_run, weather_file, result_folder):
        # Class inputs
        ## Building Characteristics
        self.building_id = building_id
        self.building_info = building_info
        ## Define directories and files
        self.filename_to_run = filename_to_run
        self.weather_file = weather_file
        self.result_folder = result_folder
        
        # Class variables
        ## handle controls
        self.got_handles = False
        self.oa_temp_handle = -1
        self.zone_temp_handle = -1
        self.zone_htg_tstat_handle = -1
        self.zone_clg_tstat_handle = -1
        ## plot settings
        self.plot_update_interval = 1  # time steps
        ## Data storage
        ### Simulation output
        self.y_outdoor = []
        self.y_radiation = []
        self.y_zone = []
        self.y_occ = []
        self.y_htg = []
        self.y_clg = []
        self.x = []
        self.energy = []
        ### Simulation timesteps (int)
        self.count = 0
        ### Aggregated simulation and control output
        self.variables_df = pd.DataFrame([])
        self.controls_df = pd.DataFrame([])
        ### Time variables
        self.years = []
        self.months = []
        self.days = []
        self.hours = []
        self.minutes = []
        self.current_times = []
        self.actual_date_times = []
        self.actual_times = []
        
    def callback_function(self, state_argument):
        
        if not self.got_handles:
            if not api.exchange.api_data_fully_ready(state_argument):
                return

            # Variable handles
            ## Zone 1
            zone_1 = "Perimeter_ZN_1"
            self.oa_temp_handle = api.exchange.get_variable_handle(
                state_argument,u"SITE OUTDOOR AIR DRYBULB TEMPERATURE", u"ENVIRONMENT")
            self.oa_radiation_handle = api.exchange.get_variable_handle(
                state_argument,u"Site Direct Solar Radiation Rate per Area", u"ENVIRONMENT")
            self.zone_temp_handle = api.exchange.get_variable_handle(
                state_argument, "Zone Mean Air Temperature", zone_1)
            self.zone_htg_tstat_handle = api.exchange.get_variable_handle(
                state_argument, "Zone Thermostat Heating Setpoint Temperature", zone_1)
            self.zone_clg_tstat_handle = api.exchange.get_variable_handle(
                state_argument, "Zone Thermostat Cooling Setpoint Temperature", zone_1)
            self.Facility_Total_Purchased_Electricity_Rate_W_handle = api.exchange.get_variable_handle(
                state_argument, "Zone Air System Sensible Cooling Rate",zone_1)
            self.zone_occupancy_handle = api.exchange.get_variable_handle(
                state_argument, "Zone People Occupant Count", zone_1)
            
            # Actuarator handles
            # Zone 1
            self.handle_clgsetp = api.exchange.get_actuator_handle(
                state_argument, "Schedule:Compact", "Schedule Value", "CLGSETP_SCH")
            self.handle_htgsetp = api.exchange.get_actuator_handle(
                state_argument, "Schedule:Compact", "Schedule Value", "HTGSETP_SCH")
            self.handle_occupancy = api.exchange.get_actuator_handle(
                state_argument, "Schedule:Compact", "Schedule Value", "BLDG_OCC_SCH")
            
            # Check whether all handels are read correctly
            if -1 in [self.oa_temp_handle, self.zone_temp_handle, self.zone_htg_tstat_handle,
                      self.zone_clg_tstat_handle, self.handle_clgsetp,  self.handle_htgsetp,
                      self.Facility_Total_Purchased_Electricity_Rate_W_handle, self.handle_occupancy, 
                      self.oa_radiation_handle, self.zone_occupancy_handle]:
                print("***Invalid handles, check spelling and sensor/actuator availability")
                sys.exit(1)
            self.got_handles = True
            
#             # draw initial plot
#             self.init_plot()

        if api.exchange.warmup_flag(state_argument):
            return
        self.count += 1
        
        # get variables via handle and save variables
        ## outdoor air temperature
        oa_temp = api.exchange.get_variable_value(state_argument, self.oa_temp_handle)
        self.y_outdoor.append(oa_temp)
        ## outdoor solar radiation
        oa_radiation = api.exchange.get_variable_value(state_argument, self.oa_radiation_handle)
        self.y_radiation.append(oa_radiation)
        ## zone air temperature
        zone_temp = api.exchange.get_variable_value(state_argument, self.zone_temp_handle)
        self.y_zone.append(zone_temp)
        ## heating setpoint
        zone_htg_tstat = api.exchange.get_variable_value(state_argument, self.zone_htg_tstat_handle)
        self.y_htg.append(zone_htg_tstat)
        ## cooling setpoint
        zone_clg_tstat = api.exchange.get_variable_value(state_argument, self.zone_clg_tstat_handle)
        self.y_clg.append(zone_clg_tstat)
        ## Electricity rate
        Facility_Total_Purchased_Electricity_Rate_W = api.exchange.get_variable_value(
            state_argument, self.Facility_Total_Purchased_Electricity_Rate_W_handle)
        self.energy.append(Facility_Total_Purchased_Electricity_Rate_W)
        # building occupancy
        zone_occupancy = api.exchange.get_variable_value(state_argument, self.zone_occupancy_handle)
        self.y_occ.append(zone_occupancy)

        # Read Time
        year = api.exchange.year(state)
        month = api.exchange.month(state)
        day = api.exchange.day_of_month(state)
        hour = api.exchange.hour(state)
        minute = api.exchange.minutes(state)
        current_time = api.exchange.current_time(state)
        actual_date_time = api.exchange.actual_date_time(state)
        actual_time = api.exchange.actual_time(state)
  
        # save time
        # TODO: now harcode it to 2009, Year is bogus, seems to be reading the weather file year instead...
        year = 2009
        self.years.append(year)
        self.months.append(month)
        self.days.append(day)
        self.hours.append(hour)
        self.minutes.append(minute)

        self.current_times.append(current_time)
        self.actual_date_times.append(actual_date_time)
        self.actual_times.append(actual_time)

        timedelta = datetime.timedelta()
        if hour >= 24.0:
            hour = 23.0
            timedelta += datetime.timedelta(hours=1)
        if minute >= 60.0:
            minute = 59
            timedelta += datetime.timedelta(minutes=1)

        dt = datetime.datetime(year=year, month=month, day=day, hour=hour, minute=minute)
        dt += timedelta
        self.x.append(dt)        

        # aggregate and varialbes to SMMM
        current_df = pd.DataFrame([[oa_temp, oa_radiation, zone_temp, zone_htg_tstat, zone_clg_tstat, zone_occupancy, Facility_Total_Purchased_Electricity_Rate_W]], columns = ['oa_temp', 'oa_radiation', 'zone_temp', 'zone_htg_tstat', 'zone_clg_tstat', 'zone_occ','clg_rate'])
        current_df = current_df.T
        current_df.to_csv(f'dynamic_simulation_result/{self.building_id}_{self.count:03}.csv')
        
        # get control signals calculated from control components to control the EnergyPlus models 
        ## 1.1 read control signal
        
        while True:
            try:
                clg_spt = pd.read_csv(
                    working_path + f'/dynamic_simulation_result/control_{self.count:03}.csv')['clg_spt'][0]
                htg_spt = pd.read_csv(
                    working_path + f'/dynamic_simulation_result/control_{self.count:03}.csv')['htg_spt'][0]
                break
            except:
                time.sleep(1)
                
        ## 1.2 set controls
        api.exchange.set_actuator_value(state_argument, self.handle_clgsetp, clg_spt)
        api.exchange.set_actuator_value(state_argument, self.handle_htgsetp, htg_spt)

### Building Components and Non-Builidng Components Functions
func1(), func2(): building components
func3(): TOU (static data), func4(): advanced model-based control (deep learning algorithm), func5(): Large Language Model interaction (API)

In [4]:
# Building 1
def func1():
    global api, state
    api = EnergyPlusAPI()
    state = api.state_manager.new_state()
    
    building_id = 'bldg_1'
    building_info = None #HOUSEID_1_info
    filename_to_run = "EnergyPlus_models/RefBldgSmallOfficeNew2004_v1.4_7.2_2B_USA_AZ_PHOENIX/RefBldgSmallOfficeNew2004_v1.4_7.2_2B_USA_AZ_PHOENIX_IML_DPC.idf"
    weather_file = 'epw_weather_files/USA_AZ_Tucson.Intl.AP.722740_TMY3.epw'
    result_folder = 'results/RefBldgSmallOfficeNew2004_v1.4_7.2_2B_USA_AZ_PHOENIX_IML_DPC/'

    g = function_n_data(building_id=building_id, building_info=building_info, filename_to_run=filename_to_run, weather_file=weather_file, result_folder=result_folder)

    api.runtime.callback_begin_zone_timestep_after_init_heat_balance(state, g.callback_function)
    api.runtime.run_energyplus(state,
        [
            '-w', g.weather_file,
            '-d', g.result_folder,
            g.filename_to_run
        ]
    )

    # reset the state first to call run_energyplus again
    api.state_manager.reset_state(state)

def func2():
    # import two models
    with open('model/model_fx_IML.pkl', 'rb') as f:
        model_fx = pickle.load(f)

    with open('model/model_fy_IML.pkl', 'rb') as g:
        model_fy = pickle.load(g)

    TOU_IML = pd.read_csv('data/TOU_IML.csv')['TOU']

    # random perturbation
    while True: 
        number_bldg_1 = 0
        
        try:
            number_bldg_1 = max([int(x[-7:-4]) for x in os.listdir(working_path + '/dynamic_simulation_result') if 'bldg_1' in x])
            
            if number_bldg_1 != 0:
#                 bldg_1 = pd.read_csv(working_path + f'/dynamic_simulation_result/bldg_1_{number_bldg_1:03}.csv')
                
                # random perturbation
                if number_bldg_1 == 1:
                    htg_spt = 20
                    clg_spt = 26
                
                if number_bldg_1 > 1:
                    
                    print(f'-----------------{number_bldg_1}----------------')
                    
                    file_list = os.listdir('dynamic_simulation_result/')
                    bldg_file_list = [x for x in file_list if 'bldg' in x][-2:]
                    summary_list = []
                    for file in bldg_file_list:
                        temp_df = pd.read_csv(f'dynamic_simulation_result/{file}')
                        temp_list = list(temp_df.T.iloc[1,:])
                        summary_list.append(temp_list)
                    summary_df = pd.DataFrame(summary_list, columns = temp_df.T.iloc[0,:]).drop(columns = ['zone_htg_tstat'])
                    summary_df_t_minus_1 = summary_df.shift(1).drop(columns = ['clg_rate'])
                    summary_df_t_minus_1.columns = [x + "_t_minus_1" for x in summary_df_t_minus_1.columns]
                    summary_df_total = pd.concat([summary_df ,summary_df_t_minus_1], axis = 1).iloc[1:].reset_index(drop=True)

                    input_list_fx = ['oa_temp', 'oa_radiation',
                                  'zone_temp', 'zone_clg_tstat',
                                  'zone_occ']

                    input_list_fy = ['oa_temp', 'oa_radiation', 'zone_temp', 'zone_clg_tstat', 'zone_occ']

                    def cost_func(u1, u2):
                        fx_predict = summary_df_total[input_list_fx].iloc[-1:]
                        fx_predict['zone_clg_tstat'] = u1

                        x1 = model_fx.predict(fx_predict)[0]

                        fy_predict = summary_df_total[input_list_fy].iloc[-1:]
                        fy_predict['zone_clg_tstat'] = u1
                        fy_predict['zone_temp'] = x1

                        fy_u1_x1_d1 = model_fy.predict(fy_predict)[0]

                        ############################################
                        fx_predict = summary_df_total[input_list_fx].iloc[-1:]
                        fx_predict['zone_clg_tstat'] = u2 
                        fx_predict['zone_temp'] = x1

                        x2 = model_fx.predict(fx_predict)[0]

                        fy_predict = summary_df_total[input_list_fy].iloc[-1:]
                        fy_predict['zone_clg_tstat'] = u2
                        fy_predict['zone_temp'] = x2

                        fy_u2_x2_d2 = model_fy.predict(fy_predict)[0]
                        print(f'x1:{x1},x2:{x2},e1: {fy_u1_x1_d1},e2:{fy_u2_x2_d2}')
#                         print(f'penalty1:{50 * abs(x1-26)**3}, penalty2:{50 * abs(x2-26)**3}')
                        print(f'DR:{TOU_IML[number_bldg_1+1]}, DR:{TOU_IML[number_bldg_1+2]}')
                        
                        if fy_u1_x1_d1 < TOU_IML[number_bldg_1+1] and fy_u2_x2_d2 < TOU_IML[number_bldg_1+2]:
#                             cost_function = fy_u1_x1_d1*TOU_IML[number_bldg_1+1] + fy_u2_x2_d2*TOU_IML[number_bldg_1+2] #+ 5 * abs(x1-24.5)**3 + 5 * abs(x2-24.5)**3
                            cost_function = fy_u1_x1_d1 + fy_u2_x2_d2
                        else:
                            cost_function = 10e7
                        print(f'cost_function:{cost_function}')
                        return cost_function

                    u1_list = list(range(22,26 + 1,1))
                    u2_list = list(range(22,26 + 1,1))

                    cost_function_min = 10e8
                    
                    u1_opt = 0
                    u2_opt = 0

                    for u1 in u1_list:
                        for u2 in u2_list:
                            print(f'u1:{u1},u2:{u2}')
                            cost_function_temp = cost_func(u1,u2)
                            if cost_function_temp < cost_function_min:
                                cost_function_min = cost_function_temp
                                u1_opt = u1
                                u2_opt = u2
                    clg_spt = u1_opt
                    htg_spt = 20
                    print(f'Cooling Setpoint: {clg_spt}')

            # save the file
            spt = pd.DataFrame([clg_spt,htg_spt], index = ['clg_spt','htg_spt']).T
            spt.to_csv(working_path + f'/dynamic_simulation_result/control_{number_bldg_1:03}.csv')
                
        except:
            time.sleep(0.5)

In [5]:
# number_bldg_1 = 60

# # import two models
# with open('model/model_fx_IML.pkl', 'rb') as f:
#     model_fx = pickle.load(f)

# with open('model/model_fy_IML.pkl', 'rb') as g:
#     model_fy = pickle.load(g)

# TOU_IML = pd.read_csv('data/TOU_IML.csv')['TOU']

# file_list = os.listdir('dynamic_simulation_result/')
# bldg_file_list = [x for x in file_list if 'bldg' in x][-2:]
# summary_list = []
# for file in bldg_file_list:
#     temp_df = pd.read_csv(f'dynamic_simulation_result/{file}')
#     temp_list = list(temp_df.T.iloc[1,:])
#     summary_list.append(temp_list)
# summary_df = pd.DataFrame(summary_list, columns = temp_df.T.iloc[0,:]).drop(columns = ['zone_htg_tstat'])
# summary_df_t_minus_1 = summary_df.shift(1).drop(columns = ['clg_rate'])
# summary_df_t_minus_1.columns = [x + "_t_minus_1" for x in summary_df_t_minus_1.columns]
# summary_df_total = pd.concat([summary_df ,summary_df_t_minus_1], axis = 1).iloc[1:].reset_index(drop=True)

# input_list_fx = ['oa_temp', 'oa_radiation',
#               'zone_temp', 'zone_clg_tstat',
#               'zone_occ']

# input_list_fy = ['oa_temp', 'oa_radiation', 'zone_temp', 'zone_clg_tstat', 'zone_occ']

# def cost_func(u1, u2):
#     fx_predict = summary_df_total[input_list_fx].iloc[-1:]
#     fx_predict['zone_clg_tstat'] = u1

#     x1 = model_fx.predict(fx_predict)[0]

#     fy_predict = summary_df_total[input_list_fy].iloc[-1:]
#     fy_predict['zone_clg_tstat'] = u1
#     fy_predict['zone_temp'] = x1

#     fy_u1_x1_d1 = model_fy.predict(fy_predict)[0]

#     ############################################
#     fx_predict = summary_df_total[input_list_fx].iloc[-1:]
#     fx_predict['zone_clg_tstat'] = u2 
#     fx_predict['zone_temp'] = x1

#     x2 = model_fx.predict(fx_predict)[0]

#     fy_predict = summary_df_total[input_list_fy].iloc[-1:]
#     fy_predict['zone_clg_tstat'] = u2
#     fy_predict['zone_temp'] = x2

#     fy_u2_x2_d2 = model_fy.predict(fy_predict)[0]
#     print(f'x1:{x1},x2:{x2},e1: {fy_u1_x1_d1*TOU_IML[number_bldg_1+1]},e2:{fy_u2_x2_d2*TOU_IML[number_bldg_1+2]}')
#     print(f'penalty1:{1000 * abs(x1-26)**3}, penalty2:{1000 * abs(x2-26)**3}')
#     cost_function = fy_u1_x1_d1*TOU_IML[number_bldg_1+1] + fy_u2_x2_d2*TOU_IML[number_bldg_1+2] + 75 * (x1-26)**2 + 75 * (x2-26)**2 
#     print(f'cost_function:{cost_function}')
#     return cost_function

# u1_list = list(range(22,30 + 1,1))
# u2_list = list(range(22,30 + 1,1))

# cost_function_min = 10e8
# u1_opt = 0
# u2_opt = 0

# for u1 in u1_list:
#     for u2 in u2_list:
#         print(f'u1:{u1},u2:{u2}')
#         cost_function_temp = cost_func(u1,u2)
#         if cost_function_temp < cost_function_min:
#             cost_function_min = cost_function_temp
#             u1_opt = u1
#             u2_opt = u2
# clg_spt = u1
# htg_spt = 20

In [6]:
# # import two models
# with open('model/model_fx_IML.pkl', 'rb') as f:
#     model_fx = pickle.load(f)

# fx_predict = summary_df_total[input_list_fx].iloc[-1:]
# #     fx_predict['zone_clg_tstat'] = u1

# fx_predict['zone_clg_tstat'] = pd.DataFrame([22])


# x1 = model_fx.predict(fx_predict)[0]

# print(fx_predict)

# print(x1)


In [7]:
# fy_predict = summary_df_total[input_list_fy].iloc[-1:]
# fy_predict['zone_clg_tstat'] = u1
# fy_predict['zone_temp'] = x1

# fy_u1_x1_d1 = model_fy.predict(fy_predict)[0]

# ############################################
# fx_predict = summary_df_total[input_list_fx].iloc[-1:]
# fx_predict['zone_clg_tstat'] = u1
# fx_predict['zone_temp'] = x1

# x2 = model_fx.predict(fx_predict)[0]

# fy_predict = summary_df_total[input_list_fy].iloc[-1:]
# fy_predict['zone_clg_tstat'] = u2
# fy_predict['zone_temp'] = x2

# fy_u2_x2_d2 = model_fy.predict(fy_predict)[0]
# print(f'x1:{x1},x2:{x2},e1: {fy_u1_x1_d1*TOU_IML[number_bldg_1+1]},e2:{fy_u2_x2_d2*TOU_IML[number_bldg_1+2]}')
# print(f'penalty1:{1000 * abs(x1-26)**3}, penalty2:{1000 * abs(x2-26)**3}')
# cost_function = fy_u1_x1_d1*TOU_IML[number_bldg_1+1] + fy_u2_x2_d2*TOU_IML[number_bldg_1+2] + 1000 * (x1-26)**2 + 1000 * (x2-26)**2 
# print(f'cost_function:{cost_function}')

### Run Co-Simulations

In [8]:
# delete all generated dynamic temp files
files = glob.glob(working_path + '/dynamic_simulation_result/*')
for f in files:
    os.remove(f)

if __name__ == '__main__':
    Thread(target = func1).start()
    Thread(target = func2).start()